3D PLOT OF THE FULL CONSTRUCTION

In [2]:
import numpy as np
import plotly.graph_objects as go

# ==========================================
# 1. Biquintic Interpolation Setup
# ==========================================
A = np.array([
    [1, 0, 0, 0,  0,  0],
    [1, 1, 1, 1,  1,  1],
    [0, 1, 0, 0,  0,  0],
    [0, 1, 2, 3,  4,  5],
    [0, 0, 2, 0,  0,  0],
    [0, 0, 2, 6, 12, 20]
], dtype=float)

A_inv = np.linalg.inv(A)
A_inv_T = A_inv.T

def build_V_matrix(f_c, fx_c, fy_c, fxx_c, fyy_c):
    V = np.zeros((6, 6))
    V[0, 0:2], V[0, 2:4], V[0, 4:6] = f_c[0, :], fy_c[0, :], fyy_c[0, :]
    V[1, 0:2], V[1, 2:4], V[1, 4:6] = f_c[1, :], fy_c[1, :], fyy_c[1, :]
    V[2, 0:2], V[3, 0:2] = fx_c[0, :], fx_c[1, :]
    V[4, 0:2], V[5, 0:2] = fxx_c[0, :], fxx_c[1, :]
    return V

# ==========================================
# 2. O(1) Local Oracles & Helper Functions
# ==========================================
def C_oracle(k):
    mock_C = {1: 2, 2: 5, 3: 4, 4: 4, 5: 1}
    return mock_C.get(k, 1)

def is_column(C_func, k):
    return C_func(k) != k

def is_solution(C_func, k):
    c_k = C_func(k)
    return c_k < k or (c_k > k and C_func(c_k) == c_k)

def get_regime_fast(a, b, C_func, K):
    N = 6 * K + 7
    if (0 <= a <= 1 and 0 <= b <= N-1) or (2 <= a <= N-1 and 6*K+5 <= b <= N-1): return 'O'
    if (2 <= a <= N-1 and 0 <= b <= 1) or (6*K+5 <= a <= N-1 and 2 <= b <= 6*K+4): return 'G'

    if b == 2:
        if 6*K+2 <= a <= 6*K+4: return 'M'
        k_m = (a + 4) // 6
        if 1 <= k_m <= K:
            col = is_column(C_func, k_m)
            if col and 6*k_m - 1 <= a <= 6*k_m + 1: return 'M'
            if not col and 6*k_m - 4 <= a <= 6*k_m + 1: return 'M'
        k_b = (a + 2) // 6
        if 1 <= k_b <= K and a == 6*k_b - 2 and is_column(C_func, k_b): return 'B'

    k_stem = (a + 3) // 6
    if 1 <= k_stem <= K and 6*k_stem - 3 <= a <= 6*k_stem - 1 and 3 <= b <= 6*k_stem + 2:
        if is_column(C_func, k_stem): return 'B'

    k_turn = a // 6
    if 1 <= k_turn <= K and 6*k_turn <= a <= 6*k_turn + 2 and 6*k_turn + 1 <= b <= 6*k_turn + 2:
        if C_func(k_turn) > k_turn and is_column(C_func, C_func(k_turn)): return 'B'

    if b % 6 == 1 or b % 6 == 2:
        l = b // 6
        if 1 <= l <= K and is_column(C_func, l):
            k_cross = (a + 3) // 6
            if 1 <= k_cross <= K and C_func(l) > k_cross > l:
                if is_column(C_func, k_cross):
                    # RESTORED: The +1 here properly creates the mathematical red gap
                    if 6*k_cross + 1 <= a <= 6*k_cross + 2: return 'B'
                else:
                    if 6*k_cross - 3 <= a <= 6*k_cross + 2: return 'B'

    return 'R'

def get_gradient_fast(a, b, C_func, K):
    N = 6 * K + 7
    # UP RULES -> returns (0, -1)
    if 2 <= a <= N-1 and 0 <= b <= 1: return 0, -1
    k_up1 = (a + 2) // 6
    if 1 <= k_up1 <= K and 6*k_up1 - 2 <= a <= 6*k_up1 - 1:
        if 2 <= b <= 6*k_up1 + 1 and is_column(C_func, k_up1): return 0, -1
        if b == 6*k_up1 + 2 and is_solution(C_func, k_up1): return 0, -1
    k_up2 = a // 6
    if 1 <= k_up2 <= K and 6*k_up2 <= a <= 6*k_up2 + 2 and b == 6*k_up2 + 1:
        if C_func(k_up2) > k_up2 and is_column(C_func, C_func(k_up2)): return 0, -1
    if b % 6 == 1:
        l = b // 6
        if 1 <= l <= K and is_column(C_func, l):
            k_cross = (a + 3) // 6
            if 1 <= k_cross <= K and C_func(l) > k_cross > l:
                if is_column(C_func, k_cross) and 6*k_cross + 1 <= a <= 6*k_cross + 2: return 0, -1
                if not is_column(C_func, k_cross) and 6*k_cross - 3 <= a <= 6*k_cross + 2: return 0, -1
        k_cross2 = (a + 3) // 6
        if 1 <= k_cross2 <= K and a == 6*k_cross2 - 3 and is_column(C_func, k_cross2):
            l2 = b // 6
            if 1 <= l2 <= K and C_func(l2) >= k_cross2 > l2: return 0, -1

    # LEFT RULES -> returns (1, 0)
    if 6*K+2 <= a <= 6*K+4 and b == 2: return 1, 0
    if 6*K+5 <= a <= N-1 and 2 <= b <= 6*K+4: return 1, 0
    if b == 2:
        k_left1 = a // 6
        if 1 <= k_left1 <= K and 6*k_left1 <= a <= 6*k_left1 + 1 and is_column(C_func, k_left1): return 1, 0
        k_left2 = (a + 4) // 6
        if 1 <= k_left2 <= K and 6*k_left2 - 4 <= a <= 6*k_left2 + 1 and not is_column(C_func, k_left2): return 1, 0

    # DOWN RULES -> returns (0, 1)
    if 2 <= a <= N-1 and 6*K+5 <= b <= N-1: return 0, 1
    if a == 6*K+4 and 3 <= b <= 6*K+4: return 0, 1
    k_down1 = (a + 2) // 6
    if 1 <= k_down1 <= K and 6*k_down1 - 2 <= a <= 6*k_down1 - 1 and 6*k_down1 + 3 <= b <= 6*K+4:
        if is_solution(C_func, k_down1): return 0, 1
    k_down2 = (a + 5) // 6
    if 2 <= k_down2 <= K and a == 6*k_down2 - 5 and b == 3:
        if is_column(C_func, k_down2): return 0, 1

    # RIGHT RULES -> returns (-1, 0)
    return -1, 0

# ==========================================
# 3. Generate Grid Node Values & Interpolate
# ==========================================
K = 5
N = 6 * K + 7
f, fx, fy = np.zeros((N, N)), np.zeros((N, N)), np.zeros((N, N))
fxx, fyy = -0.5 * np.ones((N, N)), -0.5 * np.ones((N, N))
color_map = np.empty((N, N), dtype=str)

bases = {'B': 0, 'M': 100, 'R': 200, 'G': 300, 'O': 400}

for i in range(N):
    for j in range(N):
        reg = get_regime_fast(i, j, C_oracle, K)
        color_map[i, j] = reg
        base_val = bases[reg]

        if reg == 'B': f[i, j] = base_val - i - j
        elif reg == 'M': f[i, j] = base_val + i - j
        elif reg == 'R': f[i, j] = base_val - i + j
        elif reg == 'G': f[i, j] = base_val + i - j
        elif reg == 'O': f[i, j] = base_val - i + j

        fx[i, j], fy[i, j] = get_gradient_fast(i, j, C_oracle, K)

res = 4
X_dense, Y_dense = np.linspace(0, N-1, (N-1)*res), np.linspace(0, N-1, (N-1)*res)
X_mesh, Y_mesh = np.meshgrid(X_dense, Y_dense)
Z_dense = np.zeros_like(X_mesh)

for i in range(N-1):
    for j in range(N-1):
        V = build_V_matrix(f[i:i+2, j:j+2], fx[i:i+2, j:j+2], fy[i:i+2, j:j+2],
                           fxx[i:i+2, j:j+2], fyy[i:i+2, j:j+2])
        C_coeff = A_inv @ V @ A_inv_T

        x_mask, y_mask = (X_dense >= i) & (X_dense <= i+1), (Y_dense >= j) & (Y_dense <= j+1)
        DX, DY = np.meshgrid(X_dense[x_mask] - i, Y_dense[y_mask] - j)

        val = sum(C_coeff[p, q] * (DX**p) * (DY**q) for p in range(6) for q in range(6))
        idx_y, idx_x = np.where(np.outer(y_mask, x_mask))
        Z_dense[idx_y, idx_x] = val.flatten()

# ==========================================
# 4. Interactive 3D Plotting with Plotly
# ==========================================
fig = go.Figure(data=[go.Surface(
    z=Z_dense,
    x=X_mesh,
    y=Y_mesh,
    colorscale='Plasma',
    opacity=0.9,
    name='Biquintic Surface'
)])

X_nodes, Y_nodes = np.meshgrid(np.arange(N), np.arange(N))
Z_nodes = f.T
plot_colors = {'B': 'blue', 'M': 'black', 'R': 'red', 'G': 'green', 'O': 'orange'}
C_nodes = [plot_colors[c] for c in color_map.T.flatten()]

fig.add_trace(go.Scatter3d(
    x=X_nodes.flatten(),
    y=Y_nodes.flatten(),
    z=Z_nodes.flatten(),
    mode='markers',
    marker=dict(size=3, color=C_nodes, opacity=1),
    name='Grid Nodes'
))

fig.update_layout(
    title='Interactive 3D Surface',
    autosize=False,
    width=900,
    height=800,
    margin=dict(l=65, r=50, b=65, t=90),
    scene=dict(
        xaxis_title='Grid Column (a)',
        yaxis_title='Grid Row (b)',
        zaxis_title='Function Value f(a,b)',
        camera=dict(
            eye=dict(x=1.5, y=-1.5, z=1.2)
        )
    )
)

fig.show()

SYMBOLIC EXPRESSIONS

In [3]:
import sympy as sp
import numpy as np
import plotly.graph_objects as go
from plotly.subplots import make_subplots
import numpy as np
import plotly.graph_objects as go

# --- [Symbolic Setup] ---
ord_val = 6
xs, ys = sp.symbols('x y')
full_basis = [xs**i * ys**j for i in range(ord_val) for j in range(ord_val)]

# Matrix A (Mapping coefficients to boundary constraints)
A_mat = sp.Matrix([
    [1, 0, 0, 0, 0, 0], [1, 1, 1, 1, 1, 1], [0, 1, 0, 0, 0, 0],
    [0, 1, 2, 3, 4, 5], [0, 0, 2, 0, 0, 0], [0, 0, 2, 6, 12, 20]])
Ainv = A_mat.inv()

# Corner Values
U, D, R, L  = "UP", "DOWN", "RIGHT", "LEFT"

G,R,M,B = sp.symbols('G,R,M,B')
a,b,c,d = sp.symbols('a,b,c,d')
G1, R1,M1,B1 = G, R,M,B
G2, R2,M2,B2 = G1-1, R1-1, M1-1, B1-1





groups = [
    "GROUP A",
    "GROUP B",
    "GROUP C",
    "GROUP D",
    "GROUP E",
    "GROUP F",
    "GROUP G",
    "GROUP 1",
    "GROUP 2",
    "GROUP 3",
    "GROUP 4"
]

Phis = [
    [G2, G1, R1, M1],
    [M2, M1, R1, B1],
    [M1, R2-1, R2, R1],
    [B1, R1, B2-1, B2],
    [B1, R2, R1, B2],
    [M2, M1, R2, R1],
    [M1, R2, R1, M2],
    [c,d,b,a],
    [c,d,b,a],
    [c,d,b,a],
    [c,d,b,a]
]

gradients = [
    [U, U, R, L],
    [U, L, R, U],
    [L, R, R, D],
    [U, R, U, U],
    [U, R, R, U],
    [L, L, D, R],
    [U, D, D, U],
    [R, R, R, R],
    [U, U, R, R],
    [U, U, U, R],
    [R, U, U, U]
]

# For group G we considered a rotation of the group appearing in the paper
# This is valid since rotations do not introduce SOSPs

for i in range(len(groups)):
  Phi = Phis[i]
  gradient = gradients[i]
  print(groups[i])
  Phix = [0, 0, 0, 0]
  Phiy = [0, 0, 0, 0]

  for i in range(4):
    if gradient[i] == U:
      Phiy[i] = sp.Rational('-1/2')
    elif gradient[i] == D:
      Phiy[i] = sp.Rational('1/2')
    elif gradient[i] == R:
      Phix[i] = sp.Rational('-1/2')
    elif gradient[i] == L:
      Phix[i] = sp.Rational('1/2')



  M = sp.Matrix([
      [Phi[0], Phi[3], Phiy[0], Phiy[3], sp.Rational('-1/2'), sp.Rational('-1/2')],
      [Phi[1], Phi[2], Phiy[1], Phiy[2], sp.Rational('-1/2'), sp.Rational('-1/2')],
      [Phix[0], Phix[3], 0, 0, 0, 0],
      [Phix[1], Phix[2], 0, 0, 0, 0],
      [sp.Rational('-1/2'), sp.Rational('-1/2'), 0, 0, 0, 0],
      [sp.Rational('-1/2'), sp.Rational('-1/2'), 0, 0, 0, 0]])

  coeffs = Ainv * M * Ainv.T
  P_expr = sum(coeffs[i,j] * full_basis[i*ord_val+j] for i in range(ord_val) for j in range(ord_val))

  # --- [Unconstrained Metrics] ---
  # 1. Standard Gradient Magnitude: ||grad P||
  grad_P = sp.Matrix([sp.diff(P_expr, xs), sp.diff(P_expr, ys)])

  grad_x = sp.diff(P_expr, xs)
  grad_y = sp.diff(P_expr, ys)

  # 2. Standard Hessian Eigenvalues: min(eig(H))
  H = sp.hessian(P_expr, (xs, ys))
  # Analytical min eigenvalue for 2x2 matrix: (tr(H) - sqrt(tr(H)^2 - 4*det(H))) / 2
  trace_H = H[0,0] + H[1,1]
  det_H = H[0,0]*H[1,1] - H[0,1]*H[1,0]
  min_eig_expr = (trace_H - sp.sqrt(trace_H**2 - 4*det_H)) / 2

  print("Grad_x = ",sp.simplify(grad_x))
  print("Grad_y = ",sp.simplify(grad_y))
  print("LAMBDA_MIN = ",sp.simplify(min_eig_expr),'\n')

GROUP A
Grad_x =  x**4*y**5*(-180*M + 180*R - 180) + x**4*y**4*(450*M - 450*R + 450) + x**4*y**3*(-300*M + 300*R - 300) + 30*x**4 + x**3*y**5*(360*M - 360*R + 372) + x**3*y**4*(-900*M + 900*R - 930) + x**3*y**3*(600*M - 600*R + 620) - 61*x**3 + x**2*y**5*(-180*M + 180*R - 198) + x**2*y**4*(450*M - 450*R + 495) + x**2*y**3*(-300*M + 300*R - 330) + 63*x**2/2 - x/2 + 3*y**5 - 15*y**4/2 + 5*y**3
Grad_y =  x**5*y**4*(-180*M + 180*R - 180) + x**5*y**3*(360*M - 360*R + 360) + x**5*y**2*(-180*M + 180*R - 180) + x**4*y**4*(450*M - 450*R + 465) + x**4*y**3*(-900*M + 900*R - 930) + x**4*y**2*(450*M - 450*R + 465) + x**3*y**4*(-300*M + 300*R - 330) + x**3*y**3*(600*M - 600*R + 660) + x**3*y**2*(-300*M + 300*R - 330) + 15*x*y**4 - 30*x*y**3 + 15*x*y**2 + y**4*(-30*G + 30*M + 75/2) + y**3*(60*G - 60*M - 77) + y**2*(-30*G + 30*M + 81/2) - y/2 - 1/2
LAMBDA_MIN =  x**5*y**3*(-360*M + 360*R - 360) + x**5*y**2*(540*M - 540*R + 540) - 180*x**5*y*(M - R + 1) + x**4*y**3*(900*M - 900*R + 930) + x**4*y**2*(-

Numerical Simulations

In [4]:
import sympy as sp
import numpy as np
import plotly.graph_objects as go
from plotly.subplots import make_subplots

# --- [Symbolic Setup] ---
ord_val = 6
xs, ys = sp.symbols('x y')
full_basis = [xs**i * ys**j for i in range(ord_val) for j in range(ord_val)]

# Matrix A (Mapping coefficients to boundary constraints)
A_mat = sp.Matrix([
    [1, 0, 0, 0, 0, 0], [1, 1, 1, 1, 1, 1], [0, 1, 0, 0, 0, 0],
    [0, 1, 2, 3, 4, 5], [0, 0, 2, 0, 0, 0], [0, 0, 2, 6, 12, 20]])
Ainv = A_mat.inv()

# Corner Values
U, D, R, L  = "UP", "DOWN", "RIGHT", "LEFT"

G, R_sym, M, B = sp.symbols('G,R,M,B')

G, R_sym, M, B = 800000000, 100000000, 5000000, 1000000
G1, R1, M1, B1 = G, R_sym, M, B
G2, R2, M2, B2 = G1-1, R1-1, M1-1, B1-1

groups = [
    "GROUP A", "GROUP B", "GROUP C", "GROUP D",
    "GROUP E", "GROUP F", "GROUP G"
]

Phis = [
    [G2, G1, R1, M1],
    [M2, M1, R1, B1],
    [M1, R2-1, R2, R1],
    [B1, R1, B2-1, B2],
    [B1, R2, R1, B2],
    [M2, M1, R2, R1],
    [M1, R2, R1, M2]
]

gradients = [
    ['U', 'U', 'R', 'L'],
    ['U', 'L', 'R', 'U'],
    ['L', 'R', 'R', 'D'],
    ['U', 'R', 'U', 'U'],
    ['U', 'R', 'R', 'U'],
    ['L', 'L', 'D', 'R'],
    ['U', 'D', 'D', 'U']
]

res = 300

for i in [0]:  # Or loop through range(len(Phis))
    idx = i
    Phi = Phis[i]
    gradient = gradients[i]
    print(groups[i])
    Phix = [0, 0, 0, 0]
    Phiy = [0, 0, 0, 0]

    for j in range(4):
        if gradient[j] == U:
            Phiy[j] = sp.Rational('-1/2')
        elif gradient[j] == D:
            Phiy[j] = sp.Rational('1/2')
        elif gradient[j] == R:
            Phix[j] = sp.Rational('-1/2')
        elif gradient[j] == L:
            Phix[j] = sp.Rational('1/2')

    M_mat = sp.Matrix([
        [Phi[0], Phi[3], Phiy[0], Phiy[3], -1/2, -1/2],
        [Phi[1], Phi[2], Phiy[1], Phiy[2], -1/2, -1/2],
        [Phix[0], Phix[3], 0, 0, 0, 0],
        [Phix[1], Phix[2], 0, 0, 0, 0],
        [-1/2, -1/2, 0, 0, 0, 0],
        [-1/2, -1/2, 0, 0, 0, 0]])

    coeffs = Ainv * M_mat * Ainv.T
    P_expr = sum(coeffs[i_idx, j_idx] * full_basis[i_idx*ord_val+j_idx] for i_idx in range(ord_val) for j_idx in range(ord_val))

    # --- [Unconstrained Metrics] ---
    grad_P = sp.Matrix([sp.diff(P_expr, xs), sp.diff(P_expr, ys)])
    grad_norm_expr = sp.sqrt(grad_P[0]**2 + grad_P[1]**2)

    grad_x_abs = sp.Abs(sp.diff(P_expr, xs))
    grad_y_abs = sp.Abs(sp.diff(P_expr, ys))

    H = sp.hessian(P_expr, (xs, ys))
    trace_H = H[0,0] + H[1,1]
    det_H = H[0,0]*H[1,1] - H[0,1]*H[1,0]
    min_eig_expr = (trace_H - sp.sqrt(trace_H**2 - 4*det_H)) / 2

    # Lambdify for numerical grid evaluation
    f_grad_x_abs = sp.lambdify((xs, ys), grad_x_abs, 'numpy')
    f_grad_y_abs = sp.lambdify((xs, ys), grad_y_abs, 'numpy')
    f_grad_norm = sp.lambdify((xs, ys), grad_norm_expr, 'numpy')
    f_min_eig = sp.lambdify((xs, ys), min_eig_expr, 'numpy')
    f_P = sp.lambdify((xs, ys), P_expr, 'numpy')

    # --- [Numerical Grid] ---
    x_vec = np.linspace(0, 1, res)
    y_vec = np.linspace(0, 1, res)
    X, Y = np.meshgrid(x_vec, y_vec)

    Z_P = f_P(X, Y)
    Z_grad = f_grad_norm(X, Y)
    Z_grad_x = f_grad_x_abs(X, Y)
    Z_grad_y = f_grad_y_abs(X, Y)
    Z_eig = f_min_eig(X, Y)

    # ================= [ 1x3 Heatmap Visualization ] =================
    fig_heatmaps = make_subplots(
        rows=1, cols=3,
        subplot_titles=(r"$|f_x|$ (Partial x)", r"$|f_y|$ (Partial y)", r"Min Eigenvalue $\lambda_{min}(\nabla^2 f(x,y))$"),
        specs=[[{'type': 'heatmap'}, {'type': 'heatmap'}, {'type': 'heatmap'}]],
        horizontal_spacing=0.12
    )

    # Plot 1: |Px|
    fig_heatmaps.add_trace(go.Heatmap(
        x=x_vec, y=y_vec, z=Z_grad_x,
        colorscale='Plasma',
        colorbar=dict(x=0.28, thickness=15), # Custom position
        name="|fx|"
    ), row=1, col=1)

    # Plot 2: |Py|
    fig_heatmaps.add_trace(go.Heatmap(
        x=x_vec, y=y_vec, z=Z_grad_y,
        colorscale='Plasma',
        colorbar=dict(x=0.64, thickness=15), # Custom position
        name="|fy|"
    ), row=1, col=2)

    # Plot 3: Min Eigenvalue
    fig_heatmaps.add_trace(go.Heatmap(
        x=x_vec, y=y_vec, z=Z_eig,
        colorscale='RdBu', zmid=0,
        colorbar=dict(thickness=15), # Default position (far right)
        name="Min Eig"
    ), row=1, col=3)

    fig_heatmaps.update_layout(
        title=groups[i]+": Component Derivatives and Min Eigenvalue Analysis",
        width=1400, height=450 # Widened to fit 3 plots comfortably
    )
    fig_heatmaps.show()

    # ================= [ 3D Surface Plot ] =================
    fig_3d = go.Figure()
    fig_3d.add_surface(x=X, y=Y, z=Z_P, colorscale='Reds_r', colorbar_thickness=25, colorbar_len=0.75)
    fig_3d.update_layout(title=groups[i]+": 3D Surface Plot", width=900, height=600)
    fig_3d.show()

    # --- SOSP Check Parameters ---
    epsilon_G = 1e-2  # First-order tolerance
    epsilon_H = 1e-2  # Second-order tolerance

    first_order_met = Z_grad <= epsilon_G
    second_order_met = Z_eig >= -epsilon_H
    sosp_mask = first_order_met & second_order_met

    # --- Check and Print Message ---
    if np.any(sosp_mask):
        idx_found = np.argwhere(sosp_mask)[0]
        found_x = X[idx_found[0], idx_found[1]]
        found_y = Y[idx_found[0], idx_found[1]]

        print(f"SOSP FOUND: An (eps_G={epsilon_G}, eps_H={epsilon_H})-SOSP exists in the box.")
        print(f"Example point: (x={found_x:.4f}, y={found_y:.4f})")
        print(f"Gradient Norm at point: {Z_grad[idx_found[0], idx_found[1]]:.6f}")
        print(f"Min Eigenvalue at point: {Z_eig[idx_found[0], idx_found[1]]:.6f}")
    else:
        print(f"NO SOSP FOUND: No points in the grid satisfy (eps_G={epsilon_G}, eps_H={epsilon_H}).")

    if np.any(first_order_met):
        idx_found = np.argwhere(first_order_met)[0]
        found_x = X[idx_found[0], idx_found[1]]
        found_y = Y[idx_found[0], idx_found[1]]

        print(f"FOSP FOUND: An (eps_G={epsilon_G})-FOSP exists in the box.")
        print(f"Example point: (x={found_x:.4f}, y={found_y:.4f})")
        print(f"Gradient Norm at point: {Z_grad[idx_found[0], idx_found[1]]:.6f}")
    else:
        print(f"NO FOSP FOUND: No points in the grid satisfy (eps_G={epsilon_G}).")
        print()

    print()

GROUP A


NO SOSP FOUND: No points in the grid satisfy (eps_G=0.01, eps_H=0.01).
FOSP FOUND: An (eps_G=0.01)-FOSP exists in the box.
Example point: (x=0.0000, y=0.0000)
Gradient Norm at point: 0.000000

